In [1]:
import sys
from pathlib import Path
sys.path.insert(0, str(Path.cwd().parent / 'src'))

import numpy as np
import stim
import sinter
import matplotlib.pyplot as plt
import re
import _cultiv_noise as cultiv_noise
from noise_utils import FLEXIBLE_PAIRWISE_PROFILES

%load_ext autoreload
%autoreload 2

In [2]:
# Sweep configuration
npoints = 25
p_values = np.logspace(-2.5, -1, npoints)

profiles = FLEXIBLE_PAIRWISE_PROFILES

# Circuit selection
circuit_dir = Path.cwd().parent / 'in/circuits/honeycomb_gidney'
circuit_files = sorted(circuit_dir.glob('model=SDEM3,*obs=H*.stim'))
print(f'{len(circuit_files)} circuits x {npoints} p-values x {len(profiles)} profiles = {len(circuit_files) * npoints * len(profiles)} tasks')

3 circuits x 25 p-values x 4 profiles = 300 tasks


In [ ]:
import json


def load_circuit_metadata(circ_path):
    json_path = circ_path.with_suffix('.json')
    with open(json_path) as f:
        return json.load(f)


def build_tasks(circuit_files, p_values, profiles):
    tasks = []
    for circ_path in circuit_files:
        raw = stim.Circuit.from_file(str(circ_path)).without_noise()
        info = load_circuit_metadata(circ_path)
        for profile_name, ratios in profiles.items():
            for p in p_values:
                model = cultiv_noise.NoiseModel.flexible_pairwise(
                    p_m_bulk=p * ratios['p_m_bulk'],
                    p_spam=p * ratios['p_spam'],
                    p_res=p * ratios['p_res'],
                )
                noisy = model.noisy_circuit(raw)
                metadata = {
                    'p': float(p),
                    'profile': profile_name,
                    'p_m_bulk': float(p * ratios['p_m_bulk']),
                    'p_spam': float(p * ratios['p_spam']),
                    'p_res': float(p * ratios['p_res']),
                    'noise_model': 'flexible_pairwise',
                    'k': info['k'],
                    'expected_distance': info['expected_distance'],
                    'rounds': info.get('rounds'),
                    'w': info.get('w'),
                    'h': info.get('h'),
                }
                tasks.append(sinter.Task(circuit=noisy, json_metadata=metadata))
    return tasks

In [4]:
# Sampling settings
max_shots = 100_000
max_errors = 10000
num_workers = 10
decoder_name = 'pymatching'

tasks = build_tasks(circuit_files, p_values, profiles)
print(f'{len(tasks)} tasks built. Sampling...')

results = sinter.collect(
    num_workers=num_workers,
    max_shots=max_shots,
    max_errors=max_errors,
    tasks=tasks,
    decoders=[decoder_name],
    print_progress=True,
)

print(f'\nDone: {len(results)} results collected.')

Starting 10 workers...


300 tasks built. Sampling...


300 tasks left:
  workers    decoder eta shots_left errors_left json_metadata                                                                                                                                                                                                                
        1 pymatching <1m      94607        9950 p=0.0031622776601683794,profile=measurement-limited,p_m_bulk=0.0031622776601683794,p_spam=3.162277660168379e-09,p_depolarizing=3.162277660168379e-09,noise_model=flexible_pairwise,k=1,expected_distance=3,rounds=10,w=6,h=9 
        1 pymatching   ?     100000       10000 p=0.003651741272548377,profile=measurement-limited,p_m_bulk=0.003651741272548377,p_spam=3.651741272548377e-09,p_depolarizing=3.651741272548377e-09,noise_model=flexible_pairwise,k=1,expected_distance=3,rounds=10,w=6,h=9   
        1 pymatching   ?     100000       10000 p=0.004216965034285823,profile=measurement-limited,p_m_bulk=0.004216965034285823,p_spam=4.216965034285823e-09,p_depolarizing=4


Done: 300 results collected.


In [ ]:
COLORS = {
    'balanced': '#4e79a7',
    'measurement-limited': '#e15759',
    'res-limited': '#76b7b2',
    'spam-limited': '#f28e2b',
}

LINESTYLES = {
    2: ':',
    4: '--',
    6: '-',
}


def plot_args_func(index, group_key, group_stats):
    m = group_stats[0].json_metadata
    ls = LINESTYLES.get(m['expected_distance'], '-')
    return {'linestyle': ls}


profile_names = list(profiles.keys())
n_profiles = len(profile_names)
ncols = 2
nrows = (n_profiles + ncols - 1) // ncols

fig, axes = plt.subplots(nrows, ncols, figsize=(8 * ncols, 6 * nrows), squeeze=False)

for idx, profile_name in enumerate(profile_names):
    ax = axes[idx // ncols][idx % ncols]
    profile_stats = [s for s in results if s.json_metadata['profile'] == profile_name]

    sinter.plot_error_rate(
        ax=ax,
        stats=profile_stats,
        x_func=lambda stat: stat.json_metadata['p'],
        group_func=lambda stat: f'd={stat.json_metadata["expected_distance"]}',
        plot_args_func=plot_args_func,
        failure_values_func=lambda stat: stat.json_metadata['k'],
    )

    ax.loglog()
    ax.set_xlabel('Physical Error Rate (p)')
    ax.set_ylabel('Logical Error Rate per round')
    ratios = profiles[profile_name]
    ratio_str = (
        f"p_m_bulk={ratios['p_m_bulk']:g}·p, "
        f"p_spam={ratios['p_spam']:g}·p, "
        f"p_res={ratios['p_res']:g}·p"
    )
    ax.set_title(f'{profile_name}\n{ratio_str}')
    ax.grid(which='major', linestyle='-', linewidth=0.5, alpha=0.7)
    ax.grid(which='minor', linestyle=':', linewidth=0.3, alpha=0.5)

    handles, labels = ax.get_legend_handles_labels()
    if handles:
        ax.legend(loc='lower right', frameon=True, edgecolor='black', fancybox=False)

for idx in range(n_profiles, nrows * ncols):
    fig.delaxes(axes[idx // ncols][idx % ncols])

fig.suptitle('Threshold Comparison: flexible-pairwise profiles')
fig.tight_layout()
fig.set_dpi(150)
plt.show()

In [11]:
from threshold_fit import locate_threshold, fit_threshold

# How many p-values to keep on each side of the coarse estimate when fitting
# the quadratic FSS ansatz. Default 2 -> 5-point window.
N_PER_SIDE = 2
LOGICAL_CUTOFF = 0.2 # Ignore points with logical error rate above this when fitting (to avoid saturation effects).

threshold_fits = {}
for profile_name in profile_names:
    profile_stats = [s for s in results if s.json_metadata['profile'] == profile_name]
    p_arr = np.array([s.json_metadata['p'] for s in profile_stats])
    d_arr = np.array([s.json_metadata['expected_distance'] for s in profile_stats])
    rounds_arr = np.array([s.json_metadata['rounds'] for s in profile_stats])
    k_arr = np.array([s.json_metadata['k'] for s in profile_stats])
    shots_arr = np.array([s.shots for s in profile_stats])
    errors_arr = np.array([s.errors for s in profile_stats])

    # Total logical error rate (per circuit) and binomial sigma.
    valid = (shots_arr > 0) & (errors_arr > 0) & (errors_arr < shots_arr * LOGICAL_CUTOFF)
    pL_total = np.where(valid, errors_arr / np.maximum(shots_arr, 1), np.nan)
    sigma_total = np.where(
        valid,
        np.sqrt(np.clip(pL_total * (1 - pL_total), 0, None) / np.maximum(shots_arr, 1)),
        np.nan,
    )

    # Convert to per-d-rounds, single-observable rate.
    # n_steps_total = rounds * k, n_steps_per_d = d. Scale factor = d / (rounds * k).
    scale = d_arr / (rounds_arr * k_arr)
    pL_per_d = 1 - (1 - pL_total) ** scale
    # Delta method: d/dp [1-(1-p)^s] = s*(1-p)^(s-1)
    sigma_per_d = sigma_total * scale * np.power(np.clip(1 - pL_total, 1e-300, 1), scale - 1)

    p_init = locate_threshold(p_arr, d_arr, pL_per_d)
    if p_init is None:
        print(f"{profile_name:>22s}: could not locate threshold (need >=2 distances per p)")
        threshold_fits[profile_name] = None
        continue
    try:
        fit = fit_threshold(
            p_arr, d_arr, pL_per_d,
            sigma=sigma_per_d, p_init=p_init, n_per_side=N_PER_SIDE,
        )
        threshold_fits[profile_name] = fit
        print(
            f"{profile_name:>22s}: p_init = {p_init:.4f}  "
            f"-> p_th = {fit.p_th:.4f} +/- {fit.p_th_err:.4f}  "
            f"mu = {fit.mu:.2f} +/- {fit.mu_err:.2f}  "
            f"(window={[f'{w:.4f}' for w in fit.p_window]}, n={fit.n_points})"
        )
    except Exception as e:
        print(f"{profile_name:>22s}: p_init = {p_init:.4f}, fit failed - {e}")
        threshold_fits[profile_name] = None


   measurement-limited: p_init = 0.0154  -> p_th = 0.0144 +/- 0.0001  mu = 1.02 +/- 0.04  (window=['0.0115', '0.0133', '0.0154'], n=9)
  depolarizing-limited: p_init = 0.0087  -> p_th = 0.0084 +/- 0.0000  mu = 0.91 +/- 0.02  (window=['0.0065', '0.0075', '0.0087', '0.0100', '0.0115'], n=13)
          spam-limited: p_init = 0.0649  -> p_th = 0.0968 +/- 0.0066  mu = 0.50 +/- 0.08  (window=['0.0487', '0.0562', '0.0649'], n=7)
              balanced: p_init = 0.0049  -> p_th = 0.0051 +/- 0.0000  mu = 0.91 +/- 0.03  (window=['0.0037', '0.0042', '0.0049', '0.0056'], n=11)


In [ ]:
circuit = stim.Circuit.from_file(
    str(Path.cwd().parent / 'in/circuits/honeycomb_gidney/model=SDEM3,r=16,w=10,h=15,p=0.001,obs=H,sheared=False.stim')
)


raw = circuit.without_noise()
print('=== BEFORE noise ===')
print(raw)

model = cultiv_noise.NoiseModel.flexible_pairwise(p_m_bulk=0.00, p_spam=0.00000, p_res=0.0000001)
noisy = model.noisy_circuit(raw)
print('\n=== AFTER noise ===')
print(noisy)

In [8]:
diagram = noisy.diagram('matchgraph-3d-html')
Path('matchgraph-3d.html').write_text(str(diagram), encoding='utf-8')

677592

In [20]:
tasks

[sinter.Task(circuit=stim.Circuit('''
     QUBIT_COORDS(0, 0) 0
     QUBIT_COORDS(0, 4) 1
     QUBIT_COORDS(0, 5) 2
     QUBIT_COORDS(0, 6) 3
     QUBIT_COORDS(1, 0) 4
     QUBIT_COORDS(1, 1) 5
     QUBIT_COORDS(1, 2) 6
     QUBIT_COORDS(1, 3) 7
     QUBIT_COORDS(1, 4) 8
     QUBIT_COORDS(1, 5) 9
     QUBIT_COORDS(1, 6) 10
     QUBIT_COORDS(1, 7) 11
     QUBIT_COORDS(1, 8) 12
     QUBIT_COORDS(2, 0) 13
     QUBIT_COORDS(2, 1) 14
     QUBIT_COORDS(2, 2) 15
     QUBIT_COORDS(2, 3) 16
     QUBIT_COORDS(2, 4) 17
     QUBIT_COORDS(2, 5) 18
     QUBIT_COORDS(2, 6) 19
     QUBIT_COORDS(2, 7) 20
     QUBIT_COORDS(2, 8) 21
     QUBIT_COORDS(3, 0) 22
     QUBIT_COORDS(3, 1) 23
     QUBIT_COORDS(3, 2) 24
     QUBIT_COORDS(3, 3) 25
     QUBIT_COORDS(3, 4) 26
     QUBIT_COORDS(3, 5) 27
     QUBIT_COORDS(3, 6) 28
     QUBIT_COORDS(3, 7) 29
     QUBIT_COORDS(3, 8) 30
     QUBIT_COORDS(4, 0) 31
     QUBIT_COORDS(4, 1) 32
     QUBIT_COORDS(4, 2) 33
     QUBIT_COORDS(4, 3) 34
     QUBIT_COORDS(4, 4) 35
